In [1]:
import os
# Set up R environment
if "R_HOME" not in os.environ:
    raise EnvironmentError("Set R_HOME before running this notebook.")
os.environ.setdefault("R_USER", os.environ["R_HOME"])

import numpy as np
import pandas as pd
from rpy2.robjects import numpy2ri
import rpy2.robjects as ro
from tabpfn import TabPFNRegressor
from sklearn.linear_model import LinearRegression
import json

def calculate_and_print_metrics(results_dict, target_parameter):
    """Calculates and prints MSE, bias, and variance (both averaged and vector)."""
    metrics = {}
    for method_name, results_list in results_dict.items():
        results = np.array(results_list)
        # Averaged metrics
        mse_avg = np.mean(np.mean((results - target_parameter)**2, axis=0))
        bias_avg = np.mean(np.mean(results - target_parameter, axis=0))
        variance_avg = np.mean(np.var(results, axis=0))
        metrics[method_name] = {"MSE_Avg": mse_avg, "Bias_Avg": bias_avg, "Variance_Avg": variance_avg}
        # Vector metrics
        mse_vec = np.mean((results - target_parameter)**2, axis=0).tolist()
        bias_vec = np.mean(results - target_parameter, axis=0).tolist()
        variance_vec = np.var(results, axis=0).tolist()
        metrics[method_name]["MSE_Vec"] = mse_vec
        metrics[method_name]["Bias_Vec"] = bias_vec
        metrics[method_name]["Variance_Vec"] = variance_vec
    return metrics

# Source required R scripts
r_files = ["semi_supervised_methods.R", "dataGeneration.R", "SupervisedEstimation.R"]
for file in r_files:
    ro.r['source'](file)

ro.r('library(MASS)')
ro.r('library(caret)')
ro.r('library(quantreg)')

# Extract R functions
GenerateData = ro.r['GenerateData']
SupervisedEst = ro.r['SupervisedEst']
PSSE = ro.r['PSSE']

settings = [
    {"n": n_val, "N": N_val, "p": p_val}
    for p_val in [4, 5, 6, 7, 8, 9]
    for n_val in [300, 500]
    for N_val in [500, 1000, 2000]
]

# Global parameters
rep = 500   # Number of replications
option = "i"   # Data setting
polyOrder = 4   # Polynomial order
tau_0 = 0.5   # Quantile level

# Store target parameters based on p
target_parameters = {}

for p_val in sorted(list(set(s["p"] for s in settings))):
    ro.r('set.seed(1230988)')
    LargeLabelledData = GenerateData(n=10**7, p=p_val, option=option).rx2("Data.labelled")
    target_parameter_vec = np.array(SupervisedEst(LargeLabelledData, tau=tau_0, option=option).rx2("Est.coef"))
    target_parameters[p_val] = {
        "vector": target_parameter_vec,
    }

all_results = {}

for setting in settings:
    n = setting["n"]
    N = setting["N"]
    p = setting["p"]

    target_parameter_vec = target_parameters[p]["vector"]

    results_proposed = []
    results_supervised = []
    results_pfnimputed = []
    results_pfnppi = []

    for k in range(rep):
        ro.r('set.seed({})'.format(k + 20220122))
        DesiredData = GenerateData(n=n, N=N, p=p, option=option)
        data_labelled = np.array(DesiredData.rx2("Data.labelled"))
        data_unlabelled = np.array(DesiredData.rx2("Data.unlabelled"))

        if option in ["i", "W1", "S1"]:
            model_type = "linear"
        elif option in ["ii", "W2", "S2"]:
            model_type = "logistic"
        elif option in ["iii", "W3", "S3"]:
            model_type = "quantile"
        else:
            raise ValueError("Unknown option value!")

        estimation_proposed = PSSE(numpy2ri.py2rpy(data_labelled), numpy2ri.py2rpy(data_unlabelled),
                                        type=model_type, tau=tau_0, alpha=polyOrder)
        hattheta_proposed = np.array(estimation_proposed.rx2("Hattheta"))
        results_proposed.append(hattheta_proposed)
        hattheta_supervised=np.array(SupervisedEst(numpy2ri.py2rpy(data_labelled),tau=tau_0,option=option).rx2("Est.coef"))
        results_supervised.append(hattheta_supervised)

        y_train = data_labelled[:, 0]
        X_train = data_labelled[:, 1:]
        X_test = data_unlabelled
        tabpfn_model = TabPFNRegressor()
        tabpfn_model.fit(X_train, y_train)
        y_hat_test = tabpfn_model.predict(X_test)
        y_hat_train = tabpfn_model.predict(X_train)

        X_all = np.vstack((X_test, X_train))
        y_imputed_all = np.hstack((y_hat_test, y_train))
        lin_imputation = LinearRegression()
        lin_imputation.fit(X_all, y_imputed_all)
        results_pfnimputed.append(np.concatenate(([lin_imputation.intercept_], lin_imputation.coef_)))

        lin_imputed_train = LinearRegression()
        lin_imputed_train.fit(X_train, y_hat_train)
        delta = np.concatenate(([lin_imputed_train.intercept_], lin_imputed_train.coef_)) - hattheta_supervised

        y_hat_all = np.hstack((y_hat_test, y_hat_train))
        lin_ppi = LinearRegression()
        lin_ppi.fit(X_all, y_hat_all)
        results_pfnppi.append(np.concatenate(([lin_ppi.intercept_], lin_ppi.coef_)) - delta)

        results_dict = {
            "SLZ": results_proposed,
            "Supervised": results_supervised,
            "TabPFN Imputed": results_pfnimputed,
            "TabPFN Debiased": results_pfnppi,
        }

        metrics = calculate_and_print_metrics(results_dict, target_parameter_vec) # Use the vector target parameter
        all_results[f"n={n}, N={N}, p={p}"] = metrics

with open("linear.json", "w") as f:
    json.dump(all_results, f, indent=4)

print("Simulation complete. Results saved to linear.json")

R[write to console]: Loading required package: ggplot2

R[write to console]: Use suppressPackageStartupMessages() to eliminate package startup
messages

R[write to console]: Loading required package: lattice

R[write to console]: Loading required package: SparseM



[1] "NOTE: The coefficients estimate is computed only using labelled data of size 10000000."
[1] "NOTE: The coefficients estimate is computed only using labelled data of size 10000000."
[1] "NOTE: The coefficients estimate is computed only using labelled data of size 10000000."
[1] "NOTE: The coefficients estimate is computed only using labelled data of size 10000000."
[1] "NOTE: The coefficients estimate is computed only using labelled data of size 10000000."
[1] "NOTE: The coefficients estimate is computed only using labelled data of size 10000000."


C:\Users\q24tian\AppData\Roaming\Python\Python312\site-packages\sklearn\base.py:474: FutureWarning: `BaseEstimator._validate_data` is deprecated in 1.6 and will be removed in 1.7. Use `sklearn.utils.validation.validate_data` instead. This function becomes public and is part of the scikit-learn developer API.
  warnings.warn(
C:\Users\q24tian\AppData\Roaming\Python\Python312\site-packages\sklearn\utils\deprecation.py:151: FutureWarning: 'force_all_finite' was renamed to 'ensure_all_finite' in 1.6 and will be removed in 1.8.
  warnings.warn(
C:\Users\q24tian\AppData\Roaming\Python\Python312\site-packages\sklearn\utils\deprecation.py:151: FutureWarning: 'force_all_finite' was renamed to 'ensure_all_finite' in 1.6 and will be removed in 1.8.
  warnings.warn(
C:\Users\q24tian\AppData\Roaming\Python\Python312\site-packages\sklearn\base.py:474: FutureWarning: `BaseEstimator._validate_data` is deprecated in 1.6 and will be removed in 1.7. Use `sklearn.utils.validation.validate_data` instead. T

Simulation complete. Results saved to linear.json
